# Learned Stage-Wise Curvature Tuning on Food101

This notebook evaluates Learned Stage-Wise Curvature Tuning (SW-CT) on the Food101 dataset using an ImageNet-pretrained ResNet-50.

Food101 is a large-scale food image-classification dataset containing 101 food categories. The dataset contains substantial variation in appearance, viewpoint, lighting, and presentation, making it useful for evaluating whether Learned SW-CT generalizes to a diverse natural-image classification task.

The experiments compare four conditions:

1. **Baseline** — the original pretrained ResNet with ReLU activations and a trained downstream classifier.
2. **Single-Parameter Curvature Tuning (S-CT)** — one global beta selected through validation-based exhaustive search.
3. **Learned SW-CT with fixed initialization** — four trainable stage-wise beta parameters initialized at 0.78.
4. **Learned SW-CT with random initialization** — four trainable stage-wise beta parameters independently initialized between 0.70 and 0.99.

Each condition is evaluated using seeds 42, 43, and 44.

Experiments are conducted for both 20 and 30 epochs to determine whether additional optimization improves classification performance or changes the learned stage-wise beta values.

Wall-clock execution time is also recorded to compare computational cost across Baseline, S-CT, and Learned SW-CT.

In [1]:
!nvidia-smi

Wed Oct  7 11:36:06 2026       
+-----------------------------------------------------------------------------------------+
| NVIDIA-SMI 580.82.07              Driver Version: 580.82.07      CUDA Version: 13.0     |
+-----------------------------------------+------------------------+----------------------+
| GPU  Name                 Persistence-M | Bus-Id          Disp.A | Volatile Uncorr. ECC |
| Fan  Temp   Perf          Pwr:Usage/Cap |           Memory-Usage | GPU-Util  Compute M. |
|                                         |                        |               MIG M. |
|=========================================+========================+======================|
|   0  Tesla T4                       Off |   00000000:00:04.0 Off |                    0 |
| N/A   47C    P8             10W /   70W |       0MiB /  15360MiB |      0%      Default |
|                                         |                        |                  N/A |
+-----------------------------------------+-----

In [1]:
%cd /content

!git clone -b main \
    https://github.com/NiftySnek173/research-curvature-tuning.git

%cd /content/research-curvature-tuning/src/curvature-tuning

!git branch --show-current
!git log -1 --oneline

/content
Cloning into 'curvature-tuning-research'...
remote: Enumerating objects: 631, done.
remote: Counting objects: 100% (303/303), done.
remote: Compressing objects: 100% (151/151), done.
remote: Total 631 (delta 191), reused 223 (delta 131), pack-reused 328 (from 1)
Receiving objects: 100% (631/631), 22.92 MiB | 9.03 MiB/s, done.
Resolving deltas: 100% (322/322), done.
/content/curvature-tuning-research/src/curvature-tuning
stage-wise-ct
27ee9f0 (HEAD -> stage-wise-ct, origin/stage-wise-ct, origin/HEAD) updated food 101 execution


## Environment Setup

The repository dependencies are installed before running the experiments.

After installation, the Colab runtime should be restarted so that the required package versions are loaded correctly.

In [2]:
%pip install -q -r requirements.txt
%pip install --force-reinstall --no-cache-dir "numpy==1.26.3"
!python -m pip install --no-deps "Pillow==12.3.0"

  Preparing metadata (setup.py) ... done
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 15.7/15.7 MB 55.4 MB/s eta 0:00:0000:0100:01
  Installing build dependencies ... done
  Getting requirements to build wheel ... done
  Installing backend dependencies ... done
  Preparing metadata (pyproject.toml) ... done
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 42.4/42.4 kB 1.9 MB/s eta 0:00:00
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 57.6/57.6 kB 2.2 MB/s eta 0:00:00
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 89.9/89.9 kB 5.0 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 64.9/64.9 kB 3.1 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 133.2/133.2 kB 7.6 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 2.3/2.3 MB 48.7 MB/s eta 0:00:00:00:01
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 78.4/78.4 kB 4.1 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 12.7/12.7 MB 62.9 MB/s eta 0:00:0000:0100:01
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━

In [1]:
%cd /content/research-curvature-tuning/src/curvature-tuning

import os
import torch

os.environ["WANDB_MODE"] = "disabled"

print("Working directory:", os.getcwd())
print("PyTorch:", torch.__version__)
print("CUDA available:", torch.cuda.is_available())

if torch.cuda.is_available():
    print("GPU:", torch.cuda.get_device_name(0))

!python -c "import PIL; from PIL import Image; print('Pillow:', PIL.__version__); im = Image.new('RGB', (8, 8)); im.info['xmp'] = b'\x83 tiff:Orientation=\"1\"'; assert im.getexif().get(274) == 1; print('XMP decoding check passed')"

/content/curvature-tuning-research/src/curvature-tuning
Working directory: /content/curvature-tuning-research/src/curvature-tuning
PyTorch: 2.11.0+cu128
CUDA available: True
GPU: Tesla T4
Pillow: 12.3.0
XMP decoding check passed


## Arabic Digits Dataset

Before running the experiments, the Arabic Digits data loaders are checked to confirm that the downstream dataset can be loaded correctly.

The same dataset split and random seed protocol are used for Baseline, S-CT, and Learned SW-CT so that the methods are compared under the same conditions.

In [2]:
from PIL import Image

# Keep the original method; safe to rerun this cell.
if not hasattr(Image.Image, "_original_getexif_food101"):
    Image.Image._original_getexif_food101 = Image.Image.getexif

def safe_getexif(self):
    xmp = self.info.get("xmp")

    if isinstance(xmp, bytes):
        try:
            xmp.decode("utf-8")
        except UnicodeDecodeError:
            # Remove only the unreadable metadata from this loaded image.
            self.info.pop("xmp", None)

    return Image.Image._original_getexif_food101(self)

Image.Image.getexif = safe_getexif

print("Food101 metadata workaround enabled.")

Food101 metadata workaround enabled.


In [3]:
from utils.data import get_data_loaders

train_loader, test_loader, val_loader = get_data_loaders(
    "imagenet_to_food101",
    train_batch_size=32,
    test_batch_size=128,
    seed=42,
)

print("Train samples:", len(train_loader.dataset))
print("Validation samples:", len(val_loader.dataset))
print("Test samples:", len(test_loader.dataset))

images, labels = next(iter(train_loader))

print("Image batch shape:", images.shape)
print("Label batch shape:", labels.shape)
print("Labels:", labels[:10])

README.md:   0%|          | 0.00/2.42k [00:00<?, ?B/s]

food101.py:   0%|          | 0.00/5.50k [00:00<?, ?B/s]

Generating train split: 0 examples [00:00, ? examples/s]

Generating test split: 0 examples [00:00, ? examples/s]

/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))


Train samples: 60600
Validation samples: 15150
Test samples: 25250
Image batch shape: torch.Size([32, 3, 224, 224])
Label batch shape: torch.Size([32])
Labels: tensor([13,  5,  1, 66, 89,  9, 81, 91, 35, 78])


# ResNet-50 Experiments

ResNet-50 is evaluated first because it was used during the initial development of Learned SW-CT.

The experiment compares Baseline, S-CT, fixed-initialization SW-CT, and random-initialization SW-CT.

All methods use the same ImageNet-pretrained backbone, Arabic Digits dataset split, experimental seeds, and downstream training protocol.

## ResNet-50 — 20-Epoch Evaluation

The first evaluation uses 20 training epochs.

This provides the primary reference experiment and maintains compatibility with the earlier Learned SW-CT work.

### Methods

**Baseline**

The pretrained ResNet-50 retains its original ReLU activations. The backbone is frozen and only the downstream classifier is trained.

**S-CT**

The original Single-Parameter Curvature Tuning method searches over a single beta shared throughout the network. Candidate beta values from 0.70 to 1.00 are evaluated using validation performance, and the best candidate is evaluated on the test set.

The recorded S-CT execution time includes the complete beta search rather than only the final selected beta.

**Learned SW-CT — Fixed Initialization**

Four trainable beta parameters are assigned to the four ResNet stages. All four begin at beta = 0.78.

This preserves the initialization used in the original Learned SW-CT experiments.

**Learned SW-CT — Random Initialization**

Four trainable stage-wise beta parameters are initialized independently between 0.70 and 0.99.

The random initialization is generated deterministically from the experiment seed. This allows the experiment to test whether Learned SW-CT depends on the fixed 0.78 starting value while remaining reproducible.

In [ ]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-06 03:22:11.919 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_food101_resnet50_seed42_epochs20.log
2026-10-06 03:22:11.923 | INFO     | __main__:main:78 - Running on cuda
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-06 03:30:07.847 | INFO     | __main__:main:105 - Testing baseline...
2026-10-06 03:30:07.919 | INFO     | __main__:main:116 - Number of trainable parameters: 206949
2026-10-06 03:30:07.920 | INFO     | __main__:main:117 - Starting transfer learning...
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-06 03:35:48.237 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 4.675241, Accuracy: 3.12%
2026-10-06 03:35:48.609 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 4.654339, Accuracy: 1.14%
2026-10-06 03:35:48.961 | INFO     | train:train_epoch

In [ ]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-06 12:40:07.996 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_food101_resnet50_seed43_epochs20.log
2026-10-06 12:40:08.001 | INFO     | __main__:main:78 - Running on cuda
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-06 12:47:03.394 | INFO     | __main__:main:105 - Testing baseline...
2026-10-06 12:47:03.443 | INFO     | __main__:main:116 - Number of trainable parameters: 206949
2026-10-06 12:47:03.443 | INFO     | __main__:main:117 - Starting transfer learning...
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-06 12:52:17.814 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 4.555281, Accuracy: 0.00%
2026-10-06 12:52:18.188 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 4.645754, Accuracy: 0.74%
2026-10-06 12:52:18.568 | INFO     | train:train_epoch

In [ ]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-07 03:22:11.199 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_food101_resnet50_seed44_epochs20.log
2026-10-07 03:22:11.203 | INFO     | __main__:main:78 - Running on cuda
/usr/local/lib/python3.11/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-07 03:29:35.520 | INFO     | __main__:main:105 - Testing baseline...
2026-10-07 03:29:35.563 | INFO     | __main__:main:116 - Number of trainable parameters: 206949
2026-10-07 03:29:35.564 | INFO     | __main__:main:117 - Starting transfer learning...
/usr/local/lib/python3.11/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-07 03:37:34.505 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 4.649487, Accuracy: 0.00%
2026-10-07 03:37:34.834 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 4.620826, Accuracy: 1.86%
2026-10-07 03:37:35.150 | INFO     | train:train_epoch

### Learned SW-CT with Fixed Beta Initialization

The original Learned SW-CT configuration is first reproduced using the fixed initialization:

\[[\beta_1,\beta_2,\beta_3,\beta_4]=[0.78,0.78,0.78,0.78].\]

The initial value is only a starting point. During training, the four beta parameters are optimized independently together with the downstream classifier.

These runs provide the reference against which random initialization will be compared.

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-07 11:51:25.072 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed42_epochs20_initfixed0.78_betalr0.01.log
2026-10-07 11:51:25.138 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100% 97.8M/97.8M [00:00<00:00, 152MB/s]
/usr/local/lib/python3.11/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-07 11:57:42.283 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-07 11:57:42.284 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-07 11:57:42.419 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-07 11:57:42.420 | INFO     | __main__:m

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-07 19:09:14.608 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed43_epochs20_initfixed0.78_betalr0.01.log
2026-10-07 19:09:14.672 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100% 97.8M/97.8M [00:00<00:00, 193MB/s]
/usr/local/lib/python3.11/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-07 19:15:30.026 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-07 19:15:30.026 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-07 19:15:30.152 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-07 19:15:30.153 | INFO     | __main__:m

In [4]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-10 12:28:32.298 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed44_epochs20_initfixed0.78_betalr0.01.log
2026-10-10 12:28:32.367 | INFO     | __main__:main:302 - Running on cuda
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-10 12:35:23.968 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-10 12:35:23.968 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-10 12:35:24.030 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-10 12:35:24.031 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-10 12:35:24.031 | INFO     | __main__:main:439 - Total trainable parameters: 206953
2026-10-10 12:35:25.635 | INFO     | 

### Learned SW-CT with Random Beta Initialization

The fixed beta = 0.78 initialization may raise the question of whether Learned SW-CT performs well only because its starting point was informed by the earlier S-CT experiments.

To test this dependency, each of the four stage-wise beta parameters is now initialized independently from a uniform distribution between 0.70 and 0.99.

The initialization is reproducible: the random generator is seeded using the experiment seed. Therefore, each seed always receives the same initial beta vector.

If random initialization produces similar performance to the fixed 0.78 experiment, this provides evidence that the Learned SW-CT result is not dependent on a single hand-selected initialization.

In [4]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-11 10:04:08.268 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed42_epochs20_initrandom_betalr0.01.log
2026-10-11 10:04:08.356 | INFO     | __main__:main:302 - Running on cuda
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-11 10:11:04.437 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-11 10:11:04.437 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-11 10:11:04.503 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-11 10:11:04.504 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-11 10:11:04.504 | INFO     | __main__:main:439 - Total trainable parameters: 206953
2026-10-11 10:11:06.066 |

In [4]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-11 20:31:12.057 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed43_epochs20_initrandom_betalr0.01.log
2026-10-11 20:31:12.120 | INFO     | __main__:main:302 - Running on cuda
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-11 20:37:53.771 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-11 20:37:53.771 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-11 20:37:53.830 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-11 20:37:53.831 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-11 20:37:53.831 | INFO     | __main__:main:439 - Total trainable parameters: 206953
2026-10-11 20:37:55.362

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-12 13:20:16.771 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed44_epochs20_initrandom_betalr0.01.log
2026-10-12 13:20:16.831 | INFO     | __main__:main:302 - Running on cuda
2026-10-12 13:28:18.355 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-12 13:28:18.356 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
2026-10-12 13:28:18.507 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-12 13:28:18.509 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-12 13:28:18.509 | INFO     | __main__:main:439 - Total trainable parameters: 206953
2026-10-12 13:28:21.381 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 4.690328, Accuracy: 0.00%
2026-10-12 13:29:17.407 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 

# ResNet-50 — 30-Epoch Evaluation

The same experiments are now repeated for 30 epochs.

The purpose of increasing the training budget is to determine whether the 20-epoch results are limited by insufficient optimization.

If a method improves substantially with 30 epochs, this suggests that additional optimization is useful. If performance remains similar, it indicates that the method has largely stabilized within the original 20-epoch training budget.

All other experimental settings remain unchanged.

For random-initialization SW-CT, the same seed produces exactly the same initial four-beta vector in both the 20-epoch and 30-epoch experiments. Therefore, initialization is held constant while the training duration changes.

Execution time is again recorded to measure the computational cost of extending training from 20 to 30 epochs.

In [3]:
!CUDA_VISIBLE_DEVICES=1 WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-12 13:19:32.326 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_food101_resnet50_seed42_epochs30.log
2026-10-12 13:19:32.329 | INFO     | __main__:main:78 - Running on cuda
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-12 13:27:18.354 | INFO     | __main__:main:105 - Testing baseline...
2026-10-12 13:27:18.425 | INFO     | __main__:main:116 - Number of trainable parameters: 206949
2026-10-12 13:27:18.425 | INFO     | __main__:main:117 - Starting transfer learning...
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-12 13:32:50.153 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 4.675241, Accuracy: 3.12%
2026-10-12 13:32:50.512 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 4.654339, Accuracy: 1.14%
2026-10-12 13:32:50.856 | INFO     | train:train_epoch

In [4]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-13 03:51:38.395 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_food101_resnet50_seed43_epochs30.log
2026-10-13 03:51:38.400 | INFO     | __main__:main:78 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 215MB/s]
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-13 03:58:35.142 | INFO     | __main__:main:105 - Testing baseline...
2026-10-13 03:58:35.197 | INFO     | __main__:main:116 - Number of trainable parameters: 206949
2026-10-13 03:58:35.197 | INFO     | __main__:main:117 - Starting transfer learning...
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-13 04:05:47.277 | INFO     | train:train_epoch:47 - 

In [ ]:
!CUDA_VISIBLE_DEVICES=1 WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-13 03:51:51.020 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_food101_resnet50_seed44_epochs30.log
2026-10-13 03:51:51.024 | INFO     | __main__:main:78 - Running on cuda
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-13 03:58:48.797 | INFO     | __main__:main:105 - Testing baseline...
2026-10-13 03:58:48.881 | INFO     | __main__:main:116 - Number of trainable parameters: 206949
2026-10-13 03:58:48.882 | INFO     | __main__:main:117 - Starting transfer learning...
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-13 04:05:58.055 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 4.649488, Accuracy: 0.00%
2026-10-13 04:05:58.433 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 4.620826, Accuracy: 1.86%
2026-10-13 04:05:58.808 | INFO     | train:train_epoch

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-13 14:09:45.817 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed42_epochs30_initfixed0.78_betalr0.01.log
2026-10-13 14:09:45.877 | INFO     | __main__:main:302 - Running on cuda
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-13 14:16:42.365 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-13 14:16:42.366 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-13 14:16:42.424 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-13 14:16:42.425 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-13 14:16:42.426 | INFO     | __main__:main:439 - Total trainable parameters: 206953
2026-10-13 14:16:43.934 | INFO     | 

In [ ]:
!CUDA_VISIBLE_DEVICES=1 WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-13 14:07:42.999 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed43_epochs30_initfixed0.78_betalr0.01.log
2026-10-13 14:07:43.058 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 250MB/s]
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-13 14:14:03.773 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-13 14:14:03.773 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-13 14:14:03.868 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-1

In [4]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-14 15:39:27.240 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed44_epochs30_initfixed0.78_betalr0.01.log
2026-10-14 15:39:27.304 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 180MB/s]
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-14 15:46:36.660 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-14 15:46:36.660 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-14 15:46:36.769 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-1

In [ ]:
!CUDA_VISIBLE_DEVICES=1 WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-14 15:39:29.316 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed42_epochs30_initrandom_betalr0.01.log
2026-10-14 15:39:29.372 | INFO     | __main__:main:302 - Running on cuda
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-14 15:46:46.858 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-14 15:46:46.859 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-14 15:46:46.917 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-14 15:46:46.917 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-14 15:46:46.918 | INFO     | __main__:main:439 - Total trainable parameters: 206953
2026-10-14 15:46:48.455 |

In [4]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-15 04:48:24.935 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed43_epochs30_initrandom_betalr0.01.log
2026-10-15 04:48:24.999 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 192MB/s]
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-15 04:55:01.037 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-15 04:55:01.037 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-15 04:55:01.141 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535

In [ ]:
!CUDA_VISIBLE_DEVICES=1 WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds food101 \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-15 04:48:36.021 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_food101_resnet50_seed44_epochs30_initrandom_betalr0.01.log
2026-10-15 04:48:36.083 | INFO     | __main__:main:302 - Running on cuda
/usr/local/lib/python3.13/dist-packages/PIL/TiffImagePlugin.py:950: UserWarning: Truncated File Read
  warnings.warn(str(msg))
2026-10-15 04:55:13.656 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-15 04:55:13.657 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-15 04:55:13.785 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-15 04:55:13.787 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-15 04:55:13.787 | INFO     | __main__:main:439 - Total trainable parameters: 206953
2026-10-15 04:55:15.325